In [2]:
# Importing packages

import pandas as pd
from zipfile import ZipFile
import os
import math
import numpy as np

In [3]:
# Set relative filepaths
# Download link: https://www.faa.gov/licenses_certificates/airmen_certification/releasable_airmen_download/
# Docs link: https://www.faa.gov/licenses_certificates/airmen_certification/media/HelpComm.pdf

__file__ = 'os.path.abspath('')'

script_dir = os.path.dirname(__file__) 
 # rel_path = './data/faa/pilots/CS122022.zip' # December 2022 data
rel_path = './data/faa/pilots/CS012023.zip'
abs_file_path = os.path.join(script_dir, rel_path)

In [4]:
# Read zipfile

zf = ZipFile(abs_file_path) 

In [5]:
# Load the .csv files we need from the zipfile - PILOT_BASIC and NONPILOT_BASIC

pilot = pd.read_csv(zf.open('PILOT_BASIC.csv'))
nonpilot = pd.read_csv(zf.open('NONPILOT_BASIC.csv'))

In [6]:
# Make sure the data loaded into dataframes properly (if working in Jupyter)

pilot.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 569475 entries, 0 to 569474
Data columns (total 16 columns):
 #   Column                  Non-Null Count   Dtype  
---  ------                  --------------   -----  
 0   UNIQUE ID               569475 non-null  object 
 1    FIRST NAME             569437 non-null  object 
 2    LAST NAME              569475 non-null  object 
 3    STREET 1               569475 non-null  object 
 4    STREET 2               569475 non-null  object 
 5    CITY                   569475 non-null  object 
 6    STATE                  569475 non-null  object 
 7    ZIP CODE               569475 non-null  object 
 8    COUNTRY                569475 non-null  object 
 9    REGION                 569475 non-null  object 
 10   MED CLASS              313457 non-null  float64
 11   MED DATE               313457 non-null  float64
 12   MED EXP DATE           313457 non-null  float64
 13   BASIC MED COURSE DATE  44450 non-null   float64
 14   BASIC MED CMEC DATE

In [7]:
# Check to make sure the data loaded into dataframes properly (if working in Jupyter)

nonpilot.info()

<class 'pandas.core.frame.DataFrame'>
RangeIndex: 387969 entries, 0 to 387968
Data columns (total 16 columns):
 #   Column                  Non-Null Count   Dtype  
---  ------                  --------------   -----  
 0   UNIQUE ID               387969 non-null  object 
 1    FIRST NAME             387951 non-null  object 
 2    LAST NAME              387969 non-null  object 
 3    STREET 1               387969 non-null  object 
 4    STREET 2               387969 non-null  object 
 5    CITY                   387969 non-null  object 
 6    STATE                  387969 non-null  object 
 7    ZIP CODE               387969 non-null  object 
 8    COUNTRY                387969 non-null  object 
 9    REGION                 387969 non-null  object 
 10   MED CLASS              53079 non-null   float64
 11   MED DATE               53079 non-null   float64
 12   MED EXP DATE           53079 non-null   float64
 13   BASIC MED COURSE DATE  12686 non-null   float64
 14   BASIC MED CMEC DATE

In [8]:
# Drop the empty columns at the end of each file (the 'Unnamed: 15' fields)

pilot.drop('Unnamed: 15', inplace=True, axis=1)
nonpilot.drop('Unnamed: 15', inplace=True, axis=1)

In [9]:
# Merging the two dataframes together 

joined = pd.concat([pilot, nonpilot], axis=0)

In [10]:
# How many records are in the database?
# Are any records missing?

# More than half of the rows do not have med_class, med_date, med_exp_date
# Less than 100k rows have basic_med_course_date and basic_med_cmec_date
# The FAA website states explicitly that this database is not the authoritative source for medical data
# Annd some of these records pertain to non-pilots

joined.info() 

<class 'pandas.core.frame.DataFrame'>
Int64Index: 957444 entries, 0 to 387968
Data columns (total 15 columns):
 #   Column                  Non-Null Count   Dtype  
---  ------                  --------------   -----  
 0   UNIQUE ID               957444 non-null  object 
 1    FIRST NAME             957388 non-null  object 
 2    LAST NAME              957444 non-null  object 
 3    STREET 1               957444 non-null  object 
 4    STREET 2               957444 non-null  object 
 5    CITY                   957444 non-null  object 
 6    STATE                  957444 non-null  object 
 7    ZIP CODE               957444 non-null  object 
 8    COUNTRY                957444 non-null  object 
 9    REGION                 957444 non-null  object 
 10   MED CLASS              366536 non-null  float64
 11   MED DATE               366536 non-null  float64
 12   MED EXP DATE           366536 non-null  float64
 13   BASIC MED COURSE DATE  57136 non-null   float64
 14   BASIC MED CMEC DATE

In [11]:
# Rename columns — all but UNIQUE ID have a space before the text begins, in the raw data

joined.rename(columns={"UNIQUE ID": "uniqueid", " FIRST NAME": "first_name", " LAST NAME": "last_name", " STREET 1": "street_1", " STREET 2": "street_2", " CITY": "city", " STATE": "state", " ZIP CODE": "zip_code", " COUNTRY": "country", " REGION": "region", " MED CLASS": "med_class", " MED DATE": "med_date", " MED EXP DATE": "med_exp_date", " BASIC MED COURSE DATE": "basic_med_course_date", " BASIC MED CMEC DATE": "basic_med_cmec_date"},inplace=True)

In [12]:
# Putting all of the duplicate rows into a dataframe of their own

joined2 = joined[joined.duplicated()]

In [13]:
joined['uniqueid'].nunique()

887913

In [14]:
# As of 12/19/22, there were 954,997 total records in the joined dataframe and 887,356 unique unique-ids
# There are 67,641 records in this dataframe, which shows the duplicate rows
# 954,997 - 887,356 = 67,641

# As of 1/18/23, there were 957,444 total records in the joined dataframe and 887,913 unique unique-ids
# There are 69,531 records in this dataframe, which shows the duplicate rows
# 957,444 - 887,913 = 69,531

print(joined2.info())

<class 'pandas.core.frame.DataFrame'>
Int64Index: 69531 entries, 1 to 387946
Data columns (total 15 columns):
 #   Column                 Non-Null Count  Dtype  
---  ------                 --------------  -----  
 0   uniqueid               69531 non-null  object 
 1   first_name             69530 non-null  object 
 2   last_name              69531 non-null  object 
 3   street_1               69531 non-null  object 
 4   street_2               69531 non-null  object 
 5   city                   69531 non-null  object 
 6   state                  69531 non-null  object 
 7   zip_code               69531 non-null  object 
 8   country                69531 non-null  object 
 9   region                 69531 non-null  object 
 10  med_class              53079 non-null  float64
 11  med_date               53079 non-null  float64
 12  med_exp_date           53079 non-null  float64
 13  basic_med_course_date  9899 non-null   float64
 14  basic_med_cmec_date    9899 non-null   float64
dtypes

In [15]:
# Drops duplicate rows from the dataframe
# If not done, there are duplicate records

# joined = joined.drop_duplicates()

In [16]:
# Does it seem to be in the correct range?
# Let's check each column to see what the values look like

# For the first field, uniqueid, these values should appear twice at the most — if the pilot is listed in both files
# It appears no uniqueid is listed more than twice

joined.uniqueid.value_counts()

A4729094    2
A5229409    2
C1480016    2
A1708630    2
A1708585    2
           ..
A5205829    1
A5205830    1
A5205831    1
A5205832    1
C1721657    1
Name: uniqueid, Length: 887913, dtype: int64

In [17]:
# For the rest of the fields, look at field.value_counts() only if performing operations on field
# Doing that on fields such as first_name and last_name would result in lots of different groupings that don't make sense
# Operations need done on the zip_code field though, so we'll check that out here

pd.set_option('display.max_rows', 800000) # this is so I can see full outputs printed in Jupyter
joined.zip_code.value_counts()

# Okay, there are clearly lots of US 9-digit ZIPs, as well as some 5-digit ZIPs (it seems)
# But the shorter ZIPs could be accurate, because the pilot's address is in a country other than the US (see next cell)

              7932
21231         1737
85338-1509     328
00000          310
76207-4547     307
31311          222
85215-2546     187
85027-2138     180
85212-6015     170
73705-5700     143
95301-5118     139
0000           137
32773-9307     132
81001-4829      99
75020-8411      97
10210           92
32114-3966      89
85027-2140      86
97124-6374      85
10540           82
8302            81
58202-9023      78
92020-1119      77
32901-6982      76
32043-3443      75
100621          74
33758           72
330             71
361006          71
234             69
57719-7600      68
338             67
32507-7243      62
86301-3721      61
32507-7207      61
85215-2560      59
34946-9022      57
510470          55
96002-9000      54
32960-1942      53
32506-8936      52
80112-5412      52
90640-4417      51
+234            51
114             51
85215-2562      50
10220           49
99623-9300      46
23401           46
99503-5774      46
78363-5001      46
11482           44
32507-7220  

In [18]:
# Checking the country column to see if there are countries other than the US

pd.set_option('display.max_rows', 300) # there are 195 countries in the world so if it's more than 200, take a second look
joined.country.value_counts()

# I first had the max_rows set to 200, but there were more than that. It's because in some cases, there are multiple
# islands or territories or other type of land, contained within one country
# For example: There are entries for the "Channel Isles" which are the Channel Islands - they're a part of the state of CA
# Another example is Saipan, which is the largest island in the Northern Mariana Islands, a US commonwealth
# There are a variety of different formats that non-US ZIPs come in

USA                   908566
SAUDI ARABIA            3814
UNITED KINGDOM          3318
GERMANY                 3063
CHINA                   2628
JAPAN                   2610
CANADA                  2591
KOREA REPUBLIC OF       2347
TAIWAN                  2112
INDIA                   1581
MEXICO                  1276
NETHERLANDS             1216
COLOMBIA                1054
FRANCE                  1043
SWITZERLAND              971
AUSTRALIA                898
BRAZIL                   881
THAILAND                 798
SINGAPORE                785
HONG KONG                726
UNITED ARAB EMIRAT       677
BELGIUM                  657
PHILIPPINES              605
ITALY                    575
NIGERIA                  539
BAHAMAS                  467
MALAYSIA                 430
IRELAND                  429
SPAIN                    428
RUSSIA                   410
ISRAEL                   398
NORWAY                   392
EL SALVADOR              357
AUSTRIA                  353
COSTA RICA    

In [19]:
# Creating a US 5-digit ZIP code field
# This will fill the uszip5 field with ZEROES where the country is not USA

joined['uszip5'] = np.where(joined['country'] == 'USA', joined['zip_code'].astype(str).str[:5], '')

In [20]:
# This is to be sure the 5-digit ZIPs that begin with leading 0s do have the leading 0s -
# Python strips them, and, when we export to .csv, they will not show up in Excel - so the ZIP 01234 would appear as 1234
# However, if you open the file in Sublime Text, the 0s are there

joined['uszip5'] = joined['uszip5'].str.zfill(5)

In [21]:
# Check ranges: Are numeric fields in ranges that make sense. Anything too high or too low? 
# (For example: In voter registration data are the dates of birth too recent or too long ago?)

# The only numeric fields in this dataset are the med_class, med_date, med_exp_date, basic_med_course_date and basic_med_cmec_date
# For med_class, the values should be either 1, 2 or 3, which reflect the three classes of medical licenses pilots can have

# After running the below command, you'll notice one row (2, when deduping isn't done) has the value of 8.

joined.med_class.value_counts()

1.0    164390
3.0    134981
2.0     67163
8.0         2
Name: med_class, dtype: int64

In [22]:
# Check ranges: Are numeric fields in ranges that make sense. Anything too high or too low? 
# For two of the remaining numeric fields, med_date and med_exp_date, the format is MYYYY or MMYYYY, depending on month

pd.set_option('display.max_rows', 500) # this is so I can see the full list printed in Jupyter
joined.med_date.value_counts()

# This range, and the numbers within it, look reasonable

82022.0     24490
92022.0     22404
102022.0    21527
72022.0     20276
122022.0    19599
112022.0    18839
62022.0     15453
32022.0     13991
52022.0     11952
22022.0     11356
12022.0     11041
42022.0     10945
62021.0      5936
32021.0      5759
82021.0      5716
42021.0      5442
52021.0      5383
92021.0      5366
72021.0      5280
122021.0     5263
102021.0     5023
112021.0     4920
12021.0      4339
22021.0      3996
82018.0      3240
122020.0     3072
62018.0      2914
52018.0      2837
72018.0      2821
102020.0     2784
112020.0     2581
42018.0      2478
12018.0      2474
32018.0      2460
22018.0      2150
102018.0     2111
102017.0     2063
92018.0      2038
112017.0     1882
122017.0     1725
62020.0      1680
72020.0      1622
52019.0      1577
82020.0      1454
12020.0      1451
82019.0      1427
92020.0      1413
72019.0      1362
42019.0      1356
112018.0     1355
62019.0      1324
102019.0     1303
32019.0      1255
22020.0      1233
12019.0      1207
32020.0   

In [23]:
# Check ranges: Are numeric fields in ranges that make sense. Anything too high or too low? 

pd.set_option('display.max_rows', 500) # this is so I can see the full list printed in Jupyter
joined.med_exp_date.value_counts()

32023.0     24879
62023.0     24675
22023.0     22505
42023.0     22126
52023.0     21553
12023.0     20064
82023.0     11748
72023.0     10634
102023.0    10163
92023.0     10032
112023.0     8401
122023.0     7921
122022.0     7731
112022.0     6138
102022.0     5477
92022.0      4753
82022.0      4283
72022.0      4005
62024.0      3405
82024.0      3332
32024.0      2951
72024.0      2919
62022.0      2871
102024.0     2828
92024.0      2809
52024.0      2790
22024.0      2599
42024.0      2593
12024.0      2497
32022.0      2452
52022.0      2326
42022.0      2195
112024.0     2168
12022.0      2057
22022.0      2038
122024.0     2028
82019.0      2004
12019.0      1827
52019.0      1806
62019.0      1778
32019.0      1769
122021.0     1637
72019.0      1633
102018.0     1604
42019.0      1604
102021.0     1568
22019.0      1566
112018.0     1535
112021.0     1440
72021.0      1414
122018.0     1406
92019.0      1381
82021.0      1364
102019.0     1350
62021.0      1329
92021.0   

In [24]:
# Create a field for the 'year' which reflects the year of the data. 
# This was uploaded on 1/3/2023, so the year field here will be 2023

joined['year'] = 2023

In [25]:
# We need to approach these two fields differently based on if the month is a one- or two-digit month:
# To do that, we need to change the ints into strings 

joined = joined.astype({'med_date':'string','med_exp_date':'string'})

In [26]:
# When changing med_date to string, undesired string characters come along
# Let's remove them
# But first, to do that, fill the nan values with empty strings because otherwise errors will throw

joined['med_date'].fillna("", inplace=True)

In [27]:
# Stripping undesirable characters

joined['med_date'] = joined['med_date'].map(lambda x: x.lstrip('b\'').rstrip('.0\''))

# Note: med_exp_date for some reason did not get the undesired chars attached
# But it's still a good idea to check if these values are in an appropriate range

# pd.set_option('display.max_rows', 500) # this is so I can see the full list printed in Jupyter
# joined.med_exp_date.value_counts()

In [28]:
# List comprehension to get the med_date_month out of the med_date field

joined['med_date_month'] = [x[:1] if len(x)<6 else x[:2] for x in joined['med_date']]

In [29]:
# In some instances, when Python performs operations, it changes datatypes to object
# So to make sure the month column k

joined = joined.astype({'med_date':'string'})

In [30]:
# Fill in leading zeroes for month

joined['med_date_month'] = joined['med_date_month'].str.zfill(2)

In [31]:
print(joined['med_date_month'])

0         10
1         08
2         00
3         00
4         11
          ..
387964    00
387965    00
387966    00
387967    00
387968    00
Name: med_date_month, Length: 957444, dtype: object


In [32]:
# Create the med_date_year field out of med_date

joined['med_date_year'] = joined.med_date.str[-4:]

In [33]:
# Now let's make a med_date field that is easier to read 

joined['med_date_revised'] = (joined['med_date_month'] + '/' + joined['med_date_year'])

In [34]:
# This step is cleaning up rows where the med_date_revised field shows just a / character using the mask method
# Remember, these are the non-pilot and pilot files, combined, so some of these people didn't have to take the exam

mask = joined['med_date_revised'].str.len() < 4
joined.loc[mask, 'med_date_revised'] = joined.loc[mask, 'med_date_revised'].str.replace('/', '')

In [35]:
# The med_date_revised field is the one to keep — dropping the others to avoid confusion

joined = joined.drop(columns = ['med_date','med_date_month', 'med_date_year'], axis=1)

In [36]:
joined.info()

<class 'pandas.core.frame.DataFrame'>
Int64Index: 957444 entries, 0 to 387968
Data columns (total 17 columns):
 #   Column                 Non-Null Count   Dtype  
---  ------                 --------------   -----  
 0   uniqueid               957444 non-null  object 
 1   first_name             957388 non-null  object 
 2   last_name              957444 non-null  object 
 3   street_1               957444 non-null  object 
 4   street_2               957444 non-null  object 
 5   city                   957444 non-null  object 
 6   state                  957444 non-null  object 
 7   zip_code               957444 non-null  object 
 8   country                957444 non-null  object 
 9   region                 957444 non-null  object 
 10  med_class              366536 non-null  float64
 11  med_exp_date           366536 non-null  string 
 12  basic_med_course_date  57136 non-null   float64
 13  basic_med_cmec_date    57136 non-null   float64
 14  uszip5                 957444 non-nu

In [37]:
# Removing the values that are just '00' — those are the records that did not have a med_date value

joined = joined.astype({'med_date_revised':'string'})
joined.replace('00', '', inplace=True)

In [43]:
# Convert the med_exp_date col, which is currently a string, to float for formatting purposes

joined['med_exp_date'] = pd.to_numeric(joined['med_exp_date'], downcast='float')

In [44]:
# That's all, folks!

joined.to_csv('pilots_2023.csv', index=False, float_format='%.0f')

In [ ]:
# As of 1/6/23, this script combines and cleans the PILOT_BASIC.csv and NONPILOT_BASIC.csv files
# With further work, the script could also combine those two files with the PILOT_CERT.csv and NONPILOT_CERT.csv files

In [ ]:
# Below this line is code I wrote to break up the med_date, etc., fields
# As well as a line of code that puts non-US ZIPs in their own column
# After discussing with the TAP team we realized this isn't useful 
# But I kept it here just in case we for some reason need it one day, and in case the code is useful for something else.

In [ ]:
joined.info()

# Checking to make sure astype worked as expected

In [193]:
# Fill the nan values with empty strings because otherwise errors will throw

joined['med_exp_date'].fillna("", inplace=True)

In [194]:
# Because float-string conversion, we need to strip the .0

joined['med_exp_date'] = joined['med_exp_date'].map(lambda x: x.rstrip('.0\''))

In [195]:
# List comprehension to get the med_exp_date_month out of the med_exp_date field

joined['med_exp_date_month'] = [x[:1] if len(x)<6 else x[:2] for x in joined['med_exp_date']]

In [196]:
# Create the med_exp_date_year field out of med_exp_date

joined['med_date_exp_year'] = joined.med_exp_date.str[-4:]

In [197]:
# For the other two remaining date fields, basic_med_course_date and basic_med_cmec_date the format is YYYYMMDD consistently
# Change these into strings to slice and get year, month, date into separate fields

joined = joined.astype({'basic_med_course_date':'string','basic_med_cmec_date':'string'})

In [198]:
# Now creating the year, month, date fields using slicing

joined['basic_med_course_date_year'] = joined.basic_med_course_date.str[:4]
joined['basic_med_course_date_month'] = joined.basic_med_course_date.str[4:6]
joined['basic_med_course_date_day'] = joined.basic_med_course_date.str[6:8]

joined['basic_med_cmec_date_year'] = joined.basic_med_cmec_date.str[:4]
joined['basic_med_cmec_date_month'] = joined.basic_med_cmec_date.str[4:6]
joined['basic_med_cmec_date_day'] = joined.basic_med_cmec_date.str[6:8]

In [175]:
# Creating a non-US ZIP code field

# joined['nonuszip'] = np.where(joined['country'] != 'USA', joined['zip_code'], '')